# Lab Assignment 6 — Interactive Weather & Rainfall Analysis with Plotly
**Dataset:** Open-Meteo hourly weather data near Warangal, Telangana  
**Variables:** precipitation, temperature, relative humidity, and wind speed.

This notebook adapts the CSV + Plotly workflow to the weather dataset supplied for the project. It is not earthquake data.

## 1. Import libraries

In [19]:
import pandas as pd
import numpy as np
import plotly.express as px
import plotly.graph_objects as go
from IPython.display import display

pd.set_option("display.max_columns", None)
print("Libraries imported successfully.")

Libraries imported successfully.


## 2. Load the dataset
The CSV starts with location metadata, then a blank line, then the weather-data header. `skiprows=3` skips those first three lines.

In [20]:
import os

file_path = "/content/open-meteo-17.96N79.59E259m-2.csv"

if not os.path.exists(file_path):
    raise FileNotFoundError(
        f"Could not find the dataset at '{file_path}'. "
        "Please upload the file 'open-meteo-17.96N79.59E259m-2.csv' to Colab's file explorer on the left."
    )

df = pd.read_csv(file_path, skiprows=3)
df.columns = df.columns.str.strip()
df["time"] = pd.to_datetime(df["time"], errors="coerce")

for col in df.columns:
    if col != "time":
        df[col] = pd.to_numeric(df[col], errors="coerce")

print("Dataset loaded.")
print("Rows and columns:", df.shape)
display(df.head())

Dataset loaded.
Rows and columns: (52608, 5)


,time,temperature_2m (°C),relative_humidity_2m (%),precipitation (mm),wind_speed_10m (km/h)
0,2020-01-01 00:00:00,21.6,79,0.0,13.8
1,2020-01-01 01:00:00,21.0,82,0.0,12.4
2,2020-01-01 02:00:00,20.5,84,0.0,11.0
3,2020-01-01 03:00:00,20.0,86,0.0,11.6
4,2020-01-01 04:00:00,19.6,87,0.0,12.1


## 3. Explore columns and summary statistics

In [21]:
print("Column names:", df.columns.tolist())
print("\nDataset information:")
df.info()
print("\nSummary statistics:")
display(df.describe().T)

Column names: ['time', 'temperature_2m (°C)', 'relative_humidity_2m (%)', 'precipitation (mm)', 'wind_speed_10m (km/h)']

Dataset information:
<class 'pandas.core.frame.DataFrame'>
RangeIndex: 52608 entries, 0 to 52607
Data columns (total 5 columns):
 #   Column                    Non-Null Count  Dtype         
---  ------                    --------------  -----         
 0   time                      52608 non-null  datetime64[ns]
 1   temperature_2m (°C)       52608 non-null  float64       
 2   relative_humidity_2m (%)  52608 non-null  int64         
 3   precipitation (mm)        52608 non-null  float64       
 4   wind_speed_10m (km/h)     52608 non-null  float64       
dtypes: datetime64[ns](1), float64(3), int64(1)
memory usage: 2.0 MB

Summary statistics:


,count,mean,min,25%,50%,75%,max,std
time,52608,2022-12-31 23:30:00,2020-01-01 00:00:00,2021-07-01 23:45:00,2022-12-31 23:30:00,2024-07-01 23:15:00,2025-12-31 23:00:00,NaN
temperature_2m (°C),52608.0,26.974346,11.9,24.2,26.7,29.9,42.4,4.708215
relative_humidity_2m (%),52608.0,65.210614,8.0,50.0,67.0,82.0,100.0,20.285845
precipitation (mm),52608.0,0.151353,0.0,0.0,0.0,0.0,29.6,0.771941
wind_speed_10m (km/h),52608.0,8.958196,0.0,6.1,8.4,11.4,47.5,4.11637


## 4. Check missing values and duplicates

In [22]:
print("Missing values before cleaning:")
display(df.isna().sum().to_frame("missing_values"))
print("Duplicate rows:", df.duplicated().sum())

df = df.drop_duplicates()
df = df.dropna(subset=["time"]).sort_values("time").reset_index(drop=True)

print("Dataset shape after basic cleaning:", df.shape)
print("Missing values after basic cleaning:")
display(df.isna().sum().to_frame("missing_values"))

Missing values before cleaning:


,missing_values
time,0
temperature_2m (°C),0
relative_humidity_2m (%),0
precipitation (mm),0
wind_speed_10m (km/h),0


Duplicate rows: 0
Dataset shape after basic cleaning: (52608, 5)
Missing values after basic cleaning:


,missing_values
time,0
temperature_2m (°C),0
relative_humidity_2m (%),0
precipitation (mm),0
wind_speed_10m (km/h),0


## 5. Create time-based columns

In [23]:
df["date"] = df["time"].dt.date
df["month"] = df["time"].dt.to_period("M").astype(str)
df["year"] = df["time"].dt.year
df["hour"] = df["time"].dt.hour

precip_col = "precipitation (mm)"
temp_col = "temperature_2m (°C)"
humidity_col = "relative_humidity_2m (%)"
wind_col = "wind_speed_10m (km/h)"

required = [precip_col, temp_col, humidity_col, wind_col]
missing_columns = [c for c in required if c not in df.columns]
if missing_columns:
    raise ValueError(f"Expected columns not found: {missing_columns}")

display(df[["time", "date", "month", "year", "hour", precip_col]].head())

,time,date,month,year,hour,precipitation (mm)
0,2020-01-01 00:00:00,2020-01-01,2020-01,2020,0,0.0
1,2020-01-01 01:00:00,2020-01-01,2020-01,2020,1,0.0
2,2020-01-01 02:00:00,2020-01-01,2020-01,2020,2,0.0
3,2020-01-01 03:00:00,2020-01-01,2020-01,2020,3,0.0
4,2020-01-01 04:00:00,2020-01-01,2020-01,2020,4,0.0


## 6. Interactive hourly precipitation trend

In [24]:
precip_col = "precipitation (mm)"
temp_col = "temperature_2m (°C)"
humidity_col = "relative_humidity_2m (%)"
wind_col = "wind_speed_10m (km/h)"

fig = px.line(
    df, x="time", y=precip_col,
    title="Hourly Precipitation Over Time",
    labels={"time": "Date and time", precip_col: "Precipitation (mm)"},
    hover_data=[temp_col, humidity_col, wind_col]
)
fig.update_layout(hovermode="x unified")
fig.show()

## 7. Monthly total precipitation

In [10]:
# Ensure the required time-based columns and variables exist in the session
if "month" not in df.columns:
    df["date"] = df["time"].dt.date
    df["month"] = df["time"].dt.to_period("M").astype(str)
    df["year"] = df["time"].dt.year
    df["hour"] = df["time"].dt.hour

precip_col = "precipitation (mm)"

monthly_rainfall = (
    df.groupby("month", as_index=False)[precip_col]
      .sum(min_count=1)
      .rename(columns={precip_col: "total_rainfall_mm"})
)
fig = px.bar(
    monthly_rainfall, x="month", y="total_rainfall_mm",
    title="Monthly Total Precipitation",
    labels={u"month": u"Month", u"total_rainfall_mm": u"Total precipitation (mm)"},
    hover_data={u"total_rainfall_mm": u":.2f"}
)
fig.update_xaxes(tickangle=-45)
fig.show()
display(monthly_rainfall.head())

,month,total_rainfall_mm
0,2020-01,18.5
1,2020-02,20.7
2,2020-03,14.5
3,2020-04,21.9
4,2020-05,22.4


## 8. Temperature trend

In [14]:
temp_col = "temperature_2m (°C)"

fig = px.line(df, x="time", y=temp_col, title="Temperature Trend",
              labels={"time": "Date and time", temp_col: "Temperature (°C)"})
fig.show()

## 9. Relative humidity trend

In [ ]:
fig = px.line(df, x="time", y=humidity_col, title="Relative Humidity Trend",
              labels={"time": "Date and time", humidity_col: "Relative humidity (%)"})
fig.show()

## 10. Wind speed trend

In [ ]:
fig = px.line(df, x="time", y=wind_col, title="Wind Speed Trend",
              labels={"time": "Date and time", wind_col: "Wind speed (km/h)"})
fig.show()

## 11. Precipitation vs relative humidity

In [ ]:
plot_df = df.dropna(subset=[precip_col, humidity_col, temp_col])
fig = px.scatter(
    plot_df, x=humidity_col, y=precip_col, color=temp_col,
    title="Precipitation vs Relative Humidity",
    labels={humidity_col: "Relative humidity (%)",
            precip_col: "Precipitation (mm)", temp_col: "Temperature (°C)"},
    hover_data=["time", wind_col]
)
fig.show()

## 12. Rainfall summary

In [12]:
precip_col = "precipitation (mm)"

rain = df[precip_col].dropna()
print(f"Valid precipitation observations: {len(rain):,}")
print(f"Sum of recorded hourly precipitation values: {rain.sum():.2f} mm")
print(f"Mean hourly precipitation: {rain.mean():.3f} mm")
print(f"Maximum hourly precipitation: {rain.max():.2f} mm")
print(f"Hours with precipitation greater than zero: {(rain > 0).sum():,}")

daily_rainfall = (
    df.groupby("date", as_index=False)[precip_col]
      .sum(min_count=1)
      .rename(columns={precip_col: "daily_precipitation_mm"})
)
display(daily_rainfall.sort_values("daily_precipitation_mm", ascending=False).head(10))

Valid precipitation observations: 52,608
Sum of recorded hourly precipitation values: 7962.40 mm
Mean hourly precipitation: 0.151 mm
Maximum hourly precipitation: 29.60 mm
Hours with precipitation greater than zero: 8,387


,date,daily_precipitation_mm
2128,2025-10-29,189.1
1303,2023-07-27,141.7
921,2022-07-10,102.9
920,2022-07-09,96.8
568,2021-07-22,95.9
635,2021-09-27,84.3
923,2022-07-12,76.0
1296,2023-07-20,74.0
227,2020-08-15,69.7
615,2021-09-07,69.7


## 13. Daily precipitation chart

In [13]:
fig = px.bar(
    daily_rainfall, x="date", y="daily_precipitation_mm",
    title="Daily Total Precipitation",
    labels={"date": "Date", "daily_precipitation_mm": "Daily precipitation (mm)"},
    hover_data={"daily_precipitation_mm": ":.2f"}
)
fig.show()

## 14. Conclusion
The notebook loads and inspects the weather CSV, checks missing values and duplicates, creates time-based features, and generates interactive Plotly visualizations for hourly precipitation, monthly and daily precipitation, temperature, humidity, wind speed, and the relationship between precipitation and humidity.

**Interpretation note:** precipitation totals are calculated by summing the hourly values in the supplied file. This dataset contains weather observations, not earthquake records.